# Background

Test sites
- 138: packered and running as vented
- 5: normal site
- 6: running as saline, but isn't actually (uncorrected matches old data b/c I use  
manual measurements)
- 66: packer well
- 205199: Matheson well with constant density correction but using well depth instead of  
screen midpoint b/c that is what Kathryn did
- 2052 matheson site with constant density correction with well depth entered into screen midpoint field

# Libraries, Functions, Parameters

## Libraries

In [24]:
import pandas as pd
import numpy as np
import sys
from datetime import datetime, datetime
import logging

import platform 
import os
from pathlib import Path

## Parameters

In [25]:
# parameters that will change by site
SITEID = 35 # same unique id as in the "concatenated_files" csv name- altlocationid or locationname
OUTPUT_FOLDER_NAME = '202610_template_development'
PROCESS_DATE = '2022-01-01' # first date of data you will process
INTERVAL = 60 # how frequently are baro and transducer data collected, in minutes

In [26]:
# parameters that may change by project
IDENTITY_COLUMN = 'altlocationid' # alternatively could be locationname- basically what column from the locations table are you using to ID sites
LOCATIONS = r"M:\Shared drives\UGS_Groundwater\Projects\Transducers\processed_data\202610_template_development\locations.csv"
MANUALS = r"M:\Shared drives\UGS_Groundwater\Projects\Transducers\processed_data\202610_template_development\manual_measurements.csv"

In [27]:
# parameters that will change by person
PROCESSOR = 'Diane Menuz'
GWTOOLPATH= "C:/Users/dmenuz/Documents/scripts/GroundwaterDataTools"
LLPATH="C:/Users/dmenuz/Documents/scripts/loggerloader"

## Logging and Local Libraries

Should be able to run without any changes

In [28]:
# import functions
sys.path.append(GWTOOLPATH)
import database_requests as db_req
sys.path.append(LLPATH)
import src.loggerloader as ll

In [29]:
# set up variable from the parameters
output_folder = f'M:/Shared drives/UGS_Groundwater/Projects/Transducers/processed_data/{OUTPUT_FOLDER_NAME}'
# name and location for storing logging file
file_name = f"{OUTPUT_FOLDER_NAME}_{SITEID}.log"
logging_file= f"{output_folder}\\logging\\{file_name}"
if IDENTITY_COLUMN == 'altlocationid':
    manualid = 'locationid'
elif IDENTITY_COLUMN == 'locationname':
    manualid = 'wellname'
else:
    print(f'Error! Identity column not recognized')

In [30]:
with open(logging_file, 'w'):
    pass  # This will clear the content of the log file

logging.basicConfig(
    level=logging.INFO,
    format="%(levelname)s - %(message)s",
    datefmt='%H:%M:%S',
    force=True
)

file_handler = logging.FileHandler(logging_file)  # Keep the log file handler to log new messages
file_handler.setLevel(logging.INFO)
logging.getLogger().addHandler(file_handler)

In [31]:
logging.info(datetime.now())
envi_dict = {
    "Operating System": platform.system() + " " + platform.release(),
    "Python Version": str(sys.version),
    "Pandas Version": str(pd.__version__),
    "Numpy Version": str(np.__version__),
    "Loggerloader Version": str(ll.__version__),  # Make sure ll refers to your logger library
    'Conda Environment': str(os.environ.get('CONDA_DEFAULT_ENV', 'Not available'))
}
logging.info(envi_dict)

INFO - 2026-10-21 12:24:26.764147
INFO - {'Operating System': 'Windows 11', 'Python Version': '3.12.6 | packaged by conda-forge | (main, Sep 30 2024, 17:48:58) [MSC v.1941 64 bit (AMD64)]', 'Pandas Version': '2.2.2', 'Numpy Version': '2.0.2', 'Loggerloader Version': '2.4.3', 'Conda Environment': 'Not available'}


# Read in Existing Data

In [32]:
# extract out manual and locations information for site of interest
all_manual = pd.read_csv(MANUALS, parse_dates=['readingdate'], index_col='readingdate').sort_index()
mandf = all_manual[all_manual[manualid]==SITEID]
mandf = mandf[mandf.index>=pd.to_datetime(PROCESS_DATE)]
all_locations = pd.read_csv(LOCATIONS)
site_data = all_locations[all_locations[IDENTITY_COLUMN]==SITEID]
site_metadata = site_data.iloc[0].to_dict()
# read in baro data
baroid = int(site_metadata['barologgertype'])
baro_file_name = f'P{baroid}.csv'
baro_file = f"{output_folder}\\barometer_data\\{baro_file_name}"
barod = pd.read_csv(baro_file)
barod = ll.prep_datetime_data(barod, mixed=True)
barod = barod[barod.index>=pd.to_datetime(PROCESS_DATE)]

In [33]:
logging.info(site_metadata)
site_metadata

INFO - {'locationname': 'AG13C', 'altlocationid': 35, 'wlnetworkname': 'Snake Valley', 'loggertype': 'nonvented', 'hascond': nan, 'stickup': 1.95, 'verticalmeasure': 5262.1, 'barologgertype': 9003.0, 'screen_midpoint': nan, 'density_correction': 'none', 'density_g_cm3': nan, 'has_packer': 'no', 'sensor_depth_below_casing': nan}


{'locationname': 'AG13C',
 'altlocationid': 35,
 'wlnetworkname': 'Snake Valley',
 'loggertype': 'nonvented',
 'hascond': nan,
 'stickup': 1.95,
 'verticalmeasure': 5262.1,
 'barologgertype': 9003.0,
 'screen_midpoint': nan,
 'density_correction': 'none',
 'density_g_cm3': nan,
 'has_packer': 'no',
 'sensor_depth_below_casing': nan}

# Process New Data

## Transducer Data Corrections

In [34]:
#review any notes that may be helpful
with pd.option_context('display.max_colwidth', None):
    print(mandf.notes[~mandf.notes.isna()])

Series([], Name: notes, dtype: object)


In [35]:
# read in csv file of concatenated transducer data
concat_file = Path(f"{output_folder}/concatenated_files/concat_{SITEID}.csv") # file path to where concatenated transducer data will be exported or already exists
wellraw = pd.read_csv(concat_file).reset_index().set_index('DateTime').sort_index()
wellraw.index = pd.to_datetime(wellraw.index, format='mixed')
wellraw = wellraw[wellraw.index>=pd.to_datetime(PROCESS_DATE)]
ll.plotlystuff([wellraw],["Level"], chrttitle=f'Unprocessed data for {SITEID}')

In [36]:
# for exapmle data only- not a "corrections" example
# put all of the corectins here between the wellraw.copy() and the plot
#  correct for spikes, bad chunks of data, etc.
# remove the "if" statements
wellraw2 = wellraw.copy()

if SITEID == 66:
    wellraw2 = wellraw2[wellraw2.index>=pd.to_datetime('2025-10-30 15:00')]

if SITEID in [205199, 2051, 2052]:
    wellraw2 = wellraw2[wellraw2.index<=pd.to_datetime('2022-11-15 14:00')]

ll.plotlystuff([wellraw2],["Level"], chrttitle=f'Cleaned data for {SITEID}')

In [37]:
# optional review of barometric data vs. transducer data
level_diff = barod.measuredlevel.mean() - wellraw2.Level.mean()
barod['barolevel'] = barod['measuredlevel'] - level_diff
ll.plotlystuff([wellraw2, barod],["Level", 'barolevel'], chrttitle='Baro-Well comparison')
barod.drop(columns=['barolevel'], inplace=True)

In [22]:
test = ll.detect_sectional_offsets_indexed(
    wellraw2, barod, 'Level', 'measuredlevel',
    freq='h', max_lag=24, window_size='7D'
)
ll.plot_sectional_lags_plotly(test)

c:\Users\dmenuz\AppData\Local\anaconda3\envs\datascience\Lib\site-packages\numpy\lib\_function_base_impl.py:2922: RuntimeWarning:

invalid value encountered in divide

c:\Users\dmenuz\AppData\Local\anaconda3\envs\datascience\Lib\site-packages\numpy\lib\_function_base_impl.py:2923: RuntimeWarning:

invalid value encountered in divide



## Remove Barometric Pressue

Barometric correction steps
- resample well and barometer data to the same time interval, based on the sampint
- merge well and barometer data together
- calculates incremental step changes in pressure and subtracts 100% of the barometric  
change from the total well presure change
- if well is vented, it just returns the initial wellcolumn values in the outcolumn field
- if well is packered, subtracts raw barometric pressure from raw transducer pressure and  
checks to make sure pressure values don't have offsets from older Solinst data
- density-corrects pressure reading to get accurate feet as needed

In [23]:
well = wellraw2.copy()

if site_metadata['has_packer'] == 'yes':
    if well.Level.min()<20:
        logging.warning(
            'Minimum transducer pressure below 20 ft; may need to correct for an offset')
    if barod.measuredlevel.min()<20:
        logging.warning(
            'Minimum barometer pressure below 20 ft; may need to correct for an offset')

# set parameter for well_baro_merge for vented wells
if site_metadata['loggertype'] == 'vented':
    vented=True
else:
    vented=False
# merge barometer and well data together
corrwl = ll.well_baro_merge(well, barod, 
                            barocolumn = 'measuredlevel',
                            wellcolumn = 'Level',
                            outcolumn="corrwl_temp",
                            sampint = INTERVAL,
                            vented = vented)
# directly subtract out barometeric pressure from 
if site_metadata['has_packer'] == 'yes' and site_metadata['loggertype'] != 'vented':
    logging.info('Adjusted barometric pressure using method for well with packer')
    corrwl['corrwl'] = corrwl['Level'] - corrwl['barometer']
else:
    corrwl['corrwl'] = corrwl['corrwl_temp']
if site_metadata['density_correction'] == 'constant':
    if pd.notna(site_metadata["density_g_cm3"]):
        logging.info(f'Density correction applied using {site_metadata['density_g_cm3']}')
        corrwl['corrwl'] = corrwl['corrwl']/site_metadata['density_g_cm3']
    else:
        logging.warning('Density correction needed but no density value assigned')
if site_metadata['density_correction'] == 'variable':
    logging.warning('Warning: Must conduct a variable-density density correction')

mancorr = corrwl[corrwl.index.floor('D').isin(mandf.index.floor('D'))]
ll.plotlystuff([corrwl, mancorr], 
               ["corrwl", 'corrwl'], 
               chrttypes=['lines','markers'],
               chrttitle=f'Baro-corrected data for {SITEID}',
               datatitles = ['baro-corrected levels', 'day manual was recorded'])

## Convert Pressure to DTW Below Ground

- removed any manual measurements that have been marked as rejected
- uses Drifting function to convert pressure to dtw below ground with the manual measurements
- for packer wells, calculate depth to water below ground based on stickup and sensor hanging depth
- calculates waterelevation for all sites
- calcalates freshwater equivalent head for sites with a constant density correction

In [17]:
mandf_final = mandf[mandf.datastatus!='Rejected']
print(f'{len(mandf) - len(mandf_final)} manual measurement records dropped b/c rejected in the database')

0 manual measurement records dropped b/c rejected in the database


In [18]:
DAY_BUFFER = 1 # manual measurements need to be within # day of transducer reading for correction

if site_metadata['has_packer'] == 'no':
    logging.info('Correcting site using manual measurements')
    mandf_flipped = mandf_final[['dtwbelowcasing']]
    mandf_flipped['dtwbelowground'] = mandf_flipped['dtwbelowcasing'] - site_metadata['stickup']
    mandf_flipped['dtw_below_ground_flipped'] = mandf_flipped['dtwbelowground']*-1

    dft, drift_info, mxdrft = ll.Drifting(mandf_flipped, corrwl, 
                                        drifting_field='corrwl',
                                        man_field='dtw_below_ground_flipped',
                                        daybuffer=DAY_BUFFER,
                                        output_field='measureddtw',
                                        well_id=SITEID, 
                                        trim_end=True).process_drift()
    dft['measureddtw'] = dft['measureddtw']*-1
elif site_metadata['has_packer'] == 'yes':
    logging.info('Well with packer; calculated dtw below ground using sensor depth')
    if pd.notna(site_metadata['sensor_depth_below_casing']) and pd.notna(site_metadata['stickup']):
        sensor_depth_below_ground = site_metadata['sensor_depth_below_casing']-site_metadata['stickup']
        dft = corrwl.copy()
        dft['measureddtw'] = sensor_depth_below_ground - dft['corrwl']
    else:
        logging.warning(f'Missing stickup or sensor depth values; cannot calculate measureddtw')
else:
    logging.warning(f'Packer status {site_metadata['has_packer']}; unsure how to correct data')

dft['waterelevation'] = site_metadata['verticalmeasure'] - dft['measureddtw']

if site_metadata['density_correction'] == 'constant':
    screen = site_metadata['screen_midpoint']
    density = site_metadata['density_g_cm3']
    if pd.notna(screen) and pd.notna(density):  
        logging.info(f'Calculating freshwater head equivalent using screen midpoint: {screen} and density: {density}')
        dft['dtw_ref_fluid']= screen- ((screen-dft['measureddtw'])*density)
    else:
        logging.warning(f'Missing screen depth and/or fluid density values; cannot calculate freshwater head')
elif site_metadata['density_correction'] == 'variable':
    logging.warning('Warning: Must conduct a variable-density density correction to calculate freshwater head')

INFO - Well with packer; calculated dtw below ground using sensor depth


In [19]:
if "mandf_flipped" in locals():
    ll.plotlystuff([dft, mandf_flipped], 
                ["measureddtw", 'dtwbelowground'], 
                chrttypes=['lines', 'markers'],
                chrttitle=f'Final data for {SITEID}',
                axislabels = ['DTW below ground (ft)'],
                datatitles = ['transducer reading', 'manual measurement'],
                reverse_y=True)
else:
    ll.plotlystuff([dft], 
                ["measureddtw"], 
                chrttypes=['lines'],
                chrttitle=f'Final data for {SITEID}',
                axislabels = ['DTW below ground (ft)'],
                datatitles = ['transducer reading'],
                reverse_y=True)
if site_metadata['density_correction'] == 'constant':
    ll.plotlystuff([dft, dft],
                ['dtw_ref_fluid',"measureddtw"], 
                chrttypes=['lines', 'lines'],
                chrttitle=f'Freshwater equivalent plot for {SITEID}',
                axislabels = ['DTW below ground (ft)'],
                datatitles = ['freshwater equivalent DTW','point head DTW'],
                reverse_y=True)

## TESTING ONLY: Compare to Database Data

In [ ]:
if SITEID in [205199, 2051]:
    old_reading_temp = db_req.read_datetime_data('reading', 2051, number_years=5)
    old_reading = ll.prep_datetime_data(old_reading_temp)
    old_reading = old_reading[old_reading.index<=pd.to_datetime('2022-12-01')]
else:
    old_reading_temp = db_req.read_datetime_data('reading', SITEID, number_years=5)
    old_reading = ll.prep_datetime_data(old_reading_temp, mixed=True)

In [ ]:
ll.plotlystuff([dft, old_reading],
               ["measureddtw", 'measureddtw'], 
               chrttypes=['lines', 'lines'],
               chrttitle=SITEID)

In [ ]:
# for site 66 only
if SITEID == 66:
    gap_data = pd.read_csv(r"M:\Shared drives\UGS_Groundwater\Projects\Transducers\processed_data\202610_template_development\p66_gap_fill.csv",
                        parse_dates=['readingdate'], index_col= 'readingdate')
    ll.plotlystuff([dft, gap_data, old_reading],
                ["measureddtw",'measureddtw', 'measureddtw'], 
                chrttitle=SITEID)

In [ ]:
if SITEID in [2051, 205199, 2052]:
    dft_manual = dft[dft.index.floor('D').isin(mandf_final.index.floor('D'))]
    dft_manual.rename(columns={'dtw_ref_fluid':'manual_measurement_day'}, inplace=True)
    merged_dat = pd.merge(left=dft, right=old_reading, 
                          left_index=True, right_index=True,
                          suffixes=['_new_data', '_existing_data'])
    merged_dat['diff'] = merged_dat.dtw_ref_fluid - merged_dat.measureddtw_existing_data
    merged_mask = (merged_dat.index>=pd.to_datetime('2022-03-08 12:53:00')) * (merged_dat.index<=pd.to_datetime('2022-09-20 15:15:00'))
    merged_subset = merged_dat[merged_mask]
    ll.plotlystuff([merged_subset, merged_subset, dft_manual],
               ["dtw_ref_fluid", 'measureddtw_existing_data', 'manual_measurement_day'], 
               chrttypes=['lines', 'lines', 'markers'],
               chrttitle=SITEID)

    merged_subset['diff'] = merged_subset.dtw_ref_fluid - merged_subset.measureddtw_existing_data
    print(merged_subset['diff'].describe())

## Temperature and Conductivity

In [20]:
ll.plotlystuff([dft], ['Temperature'],
              axislabels = ['temperature (F)'], )
if site_metadata['hascond']==1:
    ll.plotlystuff([dft], ['specific_conductivity'],
                   axislabels = ['specific conductivity (us/cm)'],)

# Testing New Functions

In [ ]:
import logging
from typing import Iterable, Literal, Optional, Tuple, Union
import numpy as np
import pandas as pd

logger = logging.getLogger(__name__)

DEFAULT_SPIKE_THRESHOLDS = {
    "Level": 0.5,
    "Temperature": 1.0,
    "specific_conductivity": 50.0
}

def detect_transducer_spikes(
    df: pd.DataFrame,
    value_col: str,
    datetime_col: Optional[str] = None,
    threshold: Optional[float] = None,
    param_type: Optional[str] = None,
    window: Union[int, str] = 5,
    manual_measurements: Optional[
        Union[pd.Index, pd.Series, Iterable[Union[str, pd.Timestamp]]]
    ] = None,
    manual_window: str = "2h",
    action: Literal["report", "flag", "drop"] = "drop",
    drop_near_manual_only: bool = True,
) -> Tuple[pd.DataFrame, pd.DataFrame]:
    """Detects, logs, and resolves anomalous spikes in transducer data.

    Calculates local baseline variation using a centered rolling median.
    Points deviating from the median by more than `threshold` are identified
    as spikes. Cross-references spike timestamps against manual measurements
    (e.g., field tape visits passed via DataFrame index, Series, or list).

    Args:
        df (pd.DataFrame): Input time-series DataFrame.
        value_col (str): Column name containing the sensor measurement.
        datetime_col (str, optional): Name of the timestamp column. If None,
            checks index, then 'DateTime', then 'readingdate'. Defaults to None.
        threshold (float, optional): Absolute deviation threshold. If None,
            inferred from `param_type` or `value_col`. Defaults to None.
        param_type (str, optional): Key for default threshold lookup. Defaults to None.
        window (int or str, optional): Centered rolling window size. Defaults to 5.
        manual_measurements (Index, Series, or iterable, optional): Manual visit
            timestamps (such as `manual_df.index`). Defaults to None.
        manual_window (str, optional): Proximity window around manual measurements
            (e.g., '2h', '4h', or '1D' for same-day matching). Defaults to '2h'.
        action (str, optional): Strategy to apply ('report', 'flag', 'drop'). Defaults to 'drop'.
        drop_near_manual_only (bool, optional): If True and `action='drop'`, only
            drops spikes that occurred within `manual_window` of a manual measurement.
            All other spikes are preserved. Defaults to False.

    Returns:
        tuple[pd.DataFrame, pd.DataFrame]: Processed DataFrame and summary table.
    """
    if value_col not in df.columns:
        raise KeyError(f"Target measurement column '{value_col}' not found.")

    data = df.copy()
    had_datetime_index = isinstance(data.index, pd.DatetimeIndex)

    # 1. Resolve timestamp series
    if datetime_col is not None:
        if datetime_col not in data.columns:
            raise KeyError(f"Column '{datetime_col}' not found in DataFrame.")
        ts_series = pd.to_datetime(data[datetime_col])
    elif had_datetime_index:
        ts_series = data.index.to_series()
    elif "DateTime" in data.columns:
        datetime_col = "DateTime"
        ts_series = pd.to_datetime(data["DateTime"])
    elif "readingdate" in data.columns:
        datetime_col = "readingdate"
        ts_series = pd.to_datetime(data["readingdate"])
    else:
        raise ValueError(
            "Could not detect datetime values. Specify `datetime_col` "
            "or set a DatetimeIndex on the DataFrame."
        )

    # 2. Determine threshold
    if threshold is None:
        lookup_key = (param_type or value_col).strip().lower()
        threshold = DEFAULT_SPIKE_THRESHOLDS.get(lookup_key)
        if threshold is None:
            raise ValueError(
                f"No default spike threshold found for '{lookup_key}'. "
                f"Available defaults: {list(DEFAULT_SPIKE_THRESHOLDS.keys())}. "
                "Please provide an explicit numeric `threshold`."
            )
        logger.info(
            f"Using default spike threshold of {threshold} for parameter '{lookup_key}'."
        )
    else:
        logger.info(f"Using user-defined spike threshold of {threshold}.")

    # 3. Calculate baseline and detect spikes
    data["_ts_temp"] = ts_series.values
    data = data.sort_values(by="_ts_temp")

    if isinstance(window, str):
        roll_series = data.set_index("_ts_temp")[value_col]
        rolling_median = (
            roll_series.rolling(window=window, center=True, min_periods=1)
            .median()
            .values
        )
    else:
        rolling_median = (
            data[value_col]
            .rolling(window=window, center=True, min_periods=1)
            .median()
            .values
        )

    deviations = data[value_col] - rolling_median
    spike_mask = (deviations.abs() > threshold).values
    total_spikes = int(spike_mask.sum())

    summary_cols = [
        "timestamp",
        "measured_value",
        "local_median",
        "deviation",
        "near_manual_visit",
        "nearest_manual_time",
        "time_to_manual",
        "dropped",
    ]

    if total_spikes == 0:
        logger.info(
            f"No spikes detected in column '{value_col}' using threshold {threshold}."
        )
        data.drop(columns=["_ts_temp"], inplace=True)
        if had_datetime_index:
            data = data.sort_index()
        elif datetime_col:
            data = data.sort_values(by=datetime_col)
        if action == "flag":
            data[f"is_spike_{value_col}"] = False
        return data, pd.DataFrame(columns=summary_cols)

    # 4. Parse manual measurements safely into a Series
    manual_series = None
    manual_delta_limit = None
    has_manual_data = False

    if manual_measurements is not None:
        parsed_manual = pd.Series(pd.to_datetime(manual_measurements)).dropna()
        if not parsed_manual.empty:
            manual_series = parsed_manual.sort_values().reset_index(drop=True)
            manual_delta_limit = pd.to_timedelta(manual_window)
            has_manual_data = True

    # 5. Position-based evaluation (immune to duplicate index labels)
    spike_positions = np.where(spike_mask)[0]
    near_manual_mask = np.zeros(len(data), dtype=bool)
    summary_records = []

    for pos in spike_positions:
        ts = data["_ts_temp"].iloc[pos]
        val = data[value_col].iloc[pos]
        med = rolling_median[pos]
        dev = val - med

        if has_manual_data:
            diffs = (manual_series - ts).abs()
            min_loc = diffs.idxmin()
            min_time_diff = diffs.iloc[min_loc]
            nearest_man_ts = manual_series.iloc[min_loc]
            near_manual = min_time_diff <= manual_delta_limit
            if near_manual:
                near_manual_mask[pos] = True
        else:
            near_manual = pd.NA
            nearest_man_ts = pd.NaT
            min_time_diff = pd.NaT

        # Determine if this individual spike will be dropped
        if action == "drop":
            will_drop = bool(near_manual) if drop_near_manual_only else True
        else:
            will_drop = False

        summary_records.append(
            {
                "timestamp": ts,
                "measured_value": val,
                "local_median": med,
                "deviation": dev,
                "near_manual_visit": near_manual,
                "nearest_manual_time": nearest_man_ts,
                "time_to_manual": min_time_diff,
                "dropped": will_drop,
            }
        )

    summary_df = pd.DataFrame(summary_records)
    if not has_manual_data:
        summary_df["time_to_manual"] = pd.Series(
            [pd.NaT] * len(summary_df), dtype="timedelta64[ns]"
        )

    # 6. Logging
    if has_manual_data:
        manual_correlated_count = int(near_manual_mask.sum())
        logger.warning(
            f"Detected {total_spikes} spike(s) in '{value_col}' exceeding threshold {threshold}. "
            f"({manual_correlated_count}/{total_spikes} occurred within {manual_window} of manual site visits)."
        )
    else:
        logger.warning(
            f"Detected {total_spikes} spike(s) in '{value_col}' exceeding threshold {threshold} "
            "(not evaluated against manual data)."
        )

    # 7. Execute requested action
    data.drop(columns=["_ts_temp"], inplace=True)

    if action == "flag":
        data[f"is_spike_{value_col}"] = spike_mask
        if has_manual_data:
            data[f"is_spike_near_manual_{value_col}"] = near_manual_mask

    elif action == "drop":
        if drop_near_manual_only:
            if not has_manual_data:
                logger.warning(
                    "`drop_near_manual_only` is True, but no manual measurements were provided. "
                    f"None of the {total_spikes} spikes were dropped."
                )
            else:
                dropped_count = int(near_manual_mask.sum())
                retained_count = total_spikes - dropped_count
                data = data[~near_manual_mask]
                logger.info(
                    f"Dropped {dropped_count} spike(s) occurring within {manual_window} of manual visits "
                    f"({retained_count} other spikes retained)."
                )
        else:
            data = data[~spike_mask]
            logger.info(
                f"Successfully dropped all {total_spikes} spike records from dataset."
            )

    # Restore chronological order
    if had_datetime_index:
        data = data.sort_index()
    elif datetime_col:
        data = data.sort_values(by=datetime_col)

    return data, summary_df

In [117]:
data, summary_df = detect_transducer_spikes(
    df =  dfout2,
    value_col = 'Level',
    threshold =  0.5,
    window = 5,
    manual_measurements = mandf.index,
    manual_window = "2h",
    action = "drop")

ll.plotlystuff([dfout2, data],["Level","Level"], chrttitle=f'Cleaned data for {SITEID}')

INFO - Using user-defined spike threshold of 0.5.
WARNING - Detected 5 spike(s) in 'Level' exceeding threshold 0.5. (1/5 occurred within 2h of manual site visits).
INFO - Successfully dropped all 5 spike records from dataset.


,timestamp,measured_value,local_median,deviation,near_manual_visit,nearest_manual_time,time_to_manual
0,2022-10-04 11:00:00,-2.949000,-0.317000,-2.632000,False,2023-03-08 10:19:00,154 days 23:19:00
1,2023-09-27 15:00:00,2.219000,32.478000,-30.259000,False,2023-12-06 17:27:00,70 days 02:27:00
2,2026-03-04 11:00:00,27.854332,28.395670,-0.541339,True,2026-03-04 10:35:00,0 days 00:25:00
3,2026-03-04 17:00:00,26.053150,27.962599,-1.909449,False,2026-03-04 10:35:00,0 days 06:25:00
4,2026-03-06 14:00:00,27.490158,28.848426,-1.358268,False,2026-03-04 10:35:00,2 days 03:25:00


In [110]:
summary_df

,timestamp,measured_value,local_median,deviation,near_manual_visit,nearest_manual_time,time_to_manual
0,2022-10-04 11:00:00,-2.949000,-0.317000,-2.632000,False,None,None
1,2023-09-27 15:00:00,2.219000,32.478000,-30.259000,False,None,None
2,2026-03-04 11:00:00,27.854332,28.395670,-0.541339,False,None,None
3,2026-03-04 17:00:00,26.053150,27.962599,-1.909449,False,None,None
4,2026-03-06 14:00:00,27.490158,28.848426,-1.358268,False,None,None


# Export data

In [21]:
reading_export = dft.copy()
reading_export_final = ll.clean_up_reading_columns(reading_export, SITEID)
reading_export_final.head(2)

,readingdate,measuredlevel,measureddtw,waterelevation,temperature,conductivity,locationid
0,2023-04-06 18:00:00,39.2745,-26.2745,4376.2345,12.6748,3846.326,138
1,2023-04-06 19:00:00,39.7715,-26.7715,4376.7315,12.3606,3848.958,138


**REALLY IMPORTANT! MUST MANUALLY UPDATE DATASTATUS ON DRIFT DATA IF ANYTHING BESIDES REVIEWED**

In [22]:
DATA_STATUS = 'Reviewed' # Provisional or Reviewed

if site_metadata['has_packer'] == 'yes':
    drift_dict = {
        't_beg': reading_export_final.readingdate.min(), 
        't_end': reading_export_final.readingdate.max(),
        'drift': np.nan,
        'locationid': SITEID,
        'quality': 0.3,
        'datastatus': DATA_STATUS,
        'notes': 'packered well; no manual measurements',
    }
    drift_info = pd.DataFrame([drift_dict])
else:
    drift_info['data_status'] = DATA_STATUS
    drift_info['notes'] = ""
    num_fields = ['slope_man', 'slope_trans','intercept', 'slope', 'first_meas', 'last_meas', 'first_trans', 'last_trans', 'drift', 'quality']
    drift_info[num_fields] = drift_info[num_fields].apply(lambda x: x.astype(float)).round(4)
    drift_info['locationid'] = SITEID

logging.info(f"max drift: {drift_info.drift.abs().max().round(3)}")
bad_drift = drift_info[(drift_info.drift.abs()>0.3) | (drift_info.drift.isna())]
if len(bad_drift)>0:
    print('\n')
    print('Rows with bad or na drift')
    print(drift_info.loc[(drift_info.drift.abs()>0.3) | (drift_info.drift.isna()), ['t_beg', 't_end', 'drift']])
else:
    logging.info("No NA or drift over 0.3")

INFO - max drift: nan




Rows with bad or na drift
                t_beg               t_end  drift
0 2023-04-06 18:00:00 2026-06-24 15:00:00    NaN


In [25]:
T_BEG_DATES_TO_CHANGE = ['2026-01-01'] # copy in any t_beg dates here
NEW_STATUS = 'Provisional'
STATUS_NOTES = 'suspect data; wait on next manual measurement'

drift_export = ll.update_drift_info(
        drift_info, 
        status_change_date = T_BEG_DATES_TO_CHANGE, 
        new_status = NEW_STATUS,
        notes = STATUS_NOTES)
print('Review all drift values')
drift_export[['t_beg', 't_end', 'drift', 'datastatus', 'notes']]

Review all drift values


--- Logging error ---
Traceback (most recent call last):
  File "c:\Users\dmenuz\AppData\Local\anaconda3\envs\datascience\Lib\logging\__init__.py", line 1160, in emit
    msg = self.format(record)
          ^^^^^^^^^^^^^^^^^^^
  File "c:\Users\dmenuz\AppData\Local\anaconda3\envs\datascience\Lib\logging\__init__.py", line 999, in format
    return fmt.format(record)
           ^^^^^^^^^^^^^^^^^^
  File "c:\Users\dmenuz\AppData\Local\anaconda3\envs\datascience\Lib\logging\__init__.py", line 703, in format
    record.message = record.getMessage()
                     ^^^^^^^^^^^^^^^^^^^
  File "c:\Users\dmenuz\AppData\Local\anaconda3\envs\datascience\Lib\logging\__init__.py", line 392, in getMessage
    msg = msg % self.args
          ~~~~^~~~~~~~~~~
TypeError: not all arguments converted during string formatting
Call stack:
  File "<frozen runpy>", line 198, in _run_module_as_main
  File "<frozen runpy>", line 88, in _run_code
  File "c:\Users\dmenuz\AppData\Local\anaconda3\envs\datascie

,t_beg,t_end,drift,datastatus,notes
0,2023-04-06 18:00:00,2026-06-24 15:00:00,NaN,Reviewed,packered well; no manual measurements


In [ ]:
PROCESS = 'Loggerloader in Python'
PROCESSING_NOTES = ""

process_cols = ['processor','locationid', 'processdate', 'process', 'notes', 'transducer_start_date', 'transducer_end_date', 'baroid']
process_vals = [PROCESSOR, SITEID, str(datetime.today()).split()[0], PROCESS, PROCESSING_NOTES, reading_export_final.readingdate.min(), reading_export_final.readingdate.max(), baroid]
processing_export = pd.DataFrame([process_vals], columns=process_cols)

In [ ]:
# export all data
reading_export_final.to_csv(Path(output_folder+f"/temp_processed/p{SITEID}.csv"), index=False)
drift_export.to_csv(Path(output_folder+f"/drifting/drift_{SITEID}.csv"), index=False)
processing_export.to_csv(Path(output_folder+f"/processing_table/processing_table_{SITEID}.csv"), index=False)